In [1]:
import json
import rasterio



image_dir = '/Users/isabellopez/Desktop/SURGE/data/jodhpur_image'
file1 = '/Users/isabellopez/Desktop/SURGE/data/jodhpur_annotations_annotations.json'
with open(file1) as f:
    annotations  = json.load(f)


In [2]:
import json
from shapely.geometry import Polygon, box
from shapely.ops import transform
import rasterio.features
import rasterio.warp
from rasterio.transform import Affine
from shapely.affinity import affine_transform
import geopandas as gpd


def get_bbox_polygons(image_path: str, annotations: dict):
    # Read the GeoTIFF file
    with rasterio.open(image_path) as src:
        # Get the affine transformation matrix
        transform = src.transform
        crs = src.crs
        # Create a bounding box for the entire image
        image_bbox = box(0, 0, src.width, src.height)
    
    # Transform the polygon to georeferenced coordinates
    # rasterio's transform is a 3x3 matrix, we just need the 2x3 part for shapely.affinity.affine_transform
    # the matrix should be in the format of [a, b, d, e, xoff, yoff]
    matrix = [transform.a, transform.b, transform.d, transform.e, transform.xoff, transform.yoff]
        
    georef_polygons = []
    labels = []

    # Iterate through the annotations in the COCO data
    for ann in annotations:
        # Get the bbox as x, y, width, height
        x, y, width, height = ann['bbox']

        # Create the Shapely polygon from the bbox
        polygon = Polygon([(x, y), (x, y + height), (x + width, y + height), (x + width, y)])
        #Subtract the polygon from the image bounding box
        image_bbox = image_bbox.difference(polygon)
        
        georef_polygon = affine_transform(polygon, matrix)
        

        
        # Append the georeferenced polygon to the list
        georef_polygons.append(georef_polygon)
        labels.append('tree')
    
    # Add the remaining area of the image bounding box to the list
    georef_polygons.append(affine_transform(image_bbox, matrix))
    labels.append('not tree')

    # Convert the list of polygons to a GeoSeries
    geoseries = gpd.GeoSeries(georef_polygons)

    # Convert the GeoSeries to a GeoDataFrame
    gdf = gpd.GeoDataFrame(geometry=geoseries)
    gdf['labels'] = labels
    gdf.crs = crs
    return gdf

In [3]:
annotations['images'][0]

{'id': 1,
 'width': 400,
 'height': 400,
 'file_name': '0530X3FAF8_chipid94.tiff',
 'license': 0,
 'flickr_url': '',
 'coco_url': '',
 'date_captured': 0}

In [4]:
import os

image1 = annotations['images'][0]
image_path = os.path.join(image_dir, image1['file_name'])
anns = [ann for ann in annotations['annotations'] if ann['image_id'] == image1['id']]

poly_df = get_bbox_polygons(image_path, anns)
poly_df.explore()

/opt/anaconda3/envs/visualize_DAAC/lib/python3.9/site-packages/rasterio/__init__.py:277: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be returned.
  dataset = DatasetReader(path, driver=driver, sharing=sharing, **kwargs)


In [5]:
import os
import pandas as pd

dfs = []
for image in annotations['images']:

    image_path = os.path.join(image_dir, image['file_name'])
    anns = [ann for ann in annotations['annotations'] if ann['image_id'] == image['id']]
    if len(anns):

        poly_df = get_bbox_polygons(image_path, anns)
        dfs.append(poly_df)
dfs = pd.concat(dfs)
dfs

/opt/anaconda3/envs/visualize_DAAC/lib/python3.9/site-packages/rasterio/__init__.py:277: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be returned.
  dataset = DatasetReader(path, driver=driver, sharing=sharing, **kwargs)
/opt/anaconda3/envs/visualize_DAAC/lib/python3.9/site-packages/rasterio/__init__.py:277: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be returned.
  dataset = DatasetReader(path, driver=driver, sharing=sharing, **kwargs)
/opt/anaconda3/envs/visualize_DAAC/lib/python3.9/site-packages/rasterio/__init__.py:277: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be returned.
  dataset = DatasetReader(path, driver=driver, sharing=sharing, **kwargs)
/opt/anaconda3/envs/visualize_DAAC/lib/python3.9/site-packages/rasterio/__init__.py:277: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be retu

,geometry,labels
0,"POLYGON ((338.000 64.000, 338.000 83.000, 361....",tree
1,"POLYGON ((373.000 197.000, 373.000 215.000, 39...",tree
2,"POLYGON ((330.000 6.000, 330.000 17.000, 344.0...",tree
3,"POLYGON ((328.000 272.000, 328.000 277.000, 33...",tree
4,"POLYGON ((394.000 281.000, 394.000 290.000, 40...",tree
...,...,...
12,"POLYGON ((365.000 107.000, 365.000 124.000, 38...",tree
13,"POLYGON ((363.000 152.000, 363.000 176.000, 39...",tree
14,"POLYGON ((361.000 207.000, 361.000 235.000, 39...",tree
15,"POLYGON ((0.000 318.000, 0.000 337.000, 17.000...",tree


In [6]:
dfs.explore()

In [ ]:
# for im in anns['images']:
        
#     [f['file_name'] for f in anns['images']]

In [7]:
dfs.to_file('jodhpur_anns.shp')

In [7]:
# pd.Series(out[0]).plot.hist(title='Percent Trees Matched')

In [8]:
# pd.Series(out[1]).plot.hist(title='Matched Tree IOUs')